In [1]:
import torch

device = "cuda" if torch.cuda.is_available() else "cpu"
dtype = torch.bfloat16 if torch.cuda.get_device_capability()[0] >= 8 else torch.float16

In [2]:
#old:load and preprocess images,[4, 3, 518, 518]
#new:load and preprocess images,[4, 3, 512, 512]
from PIL import Image
from torchvision import transforms as TF
# from vggt.utils.load_fn import load_and_preprocess_images
image_names = ["/data/train/train_30/2025-08-19_19-35-52/render_3d.png",
               "/data/train/train_30/2025-08-19_19-35-53/render_3d.png",
               "/data/train/train_30/2025-08-19_19-35-54/render_3d.png",
               "/data/train/train_30/2025-08-19_19-35-55/render_3d.png"
            ] 

images = []
to_tensor = TF.ToTensor()
for image_path in image_names:
   # Open image
   img = Image.open(image_path)
   img = img.convert("RGB")
   img_tensor = to_tensor(img)
   images.append(img_tensor) 
images = torch.stack(images, dim=0)  # (N, 3, H, W)

# images = load_and_preprocess_images(image_names).to(device)

print(f"Preprocessed images shape: {images.shape}")


Preprocessed images shape: torch.Size([4, 3, 512, 512])


In [3]:
predictions = { "images":images.numpy(force=True) }

In [4]:
# add extrinsic and intrinsic to predictions
from utils.camera import parse_json_camera_extrinsic_intrinsic

json_paths = [
    "/data/train/train_30/2025-08-19_19-35-52/camconf.json",
    "/data/train/train_30/2025-08-19_19-35-53/camconf.json",
    "/data/train/train_30/2025-08-19_19-35-54/camconf.json",
    "/data/train/train_30/2025-08-19_19-35-55/camconf.json",
]

H, W = 512, 512
device = "cuda"

extrinsics = []
intrinsics = []
for jp in json_paths:
    ext44, K33 = parse_json_camera_extrinsic_intrinsic(jp, device=device, H=H, W=W)  # ext44: (1,4,4), K33: (1,3,3)
    
    
    ext44[:, 2, :] *= -1  # Invert the Z axis
    Rx = torch.tensor([[1, 0,  0],
                       [0, 0, -1],
                       [0, 1,  0]], device=device, dtype=ext44.dtype)
    ext44[:, :3, :3] = ext44[:, :3, :3] @ Rx
    
    # ext44[:, :3, 3] = (Rx @ ext44[:, :3, 3].T).T
    ext34 = ext44[:, :3, :]     # (1,3,4) 取前 3 行
    extrinsics.append(ext34)
    intrinsics.append(K33)

# 拼成 [1, 4, 3, 4] 和 [1, 4, 3, 3]
extrinsic = torch.stack(extrinsics, dim=1)   # (1,4,3,4)
intrinsic = torch.stack(intrinsics, dim=1)   # (1,4,3,3)

print("extrinsic:", extrinsic.shape, extrinsic.device)
print("intrinsic:", intrinsic.shape, intrinsic.device)

predictions["extrinsic"] = extrinsic
predictions["intrinsic"] = intrinsic



extrinsic: torch.Size([1, 4, 3, 4]) cuda:0
intrinsic: torch.Size([1, 4, 3, 3]) cuda:0


In [5]:
# Convert tensors to numpy
for key in ["extrinsic", "intrinsic"]:
    if isinstance(predictions[key], torch.Tensor):
        predictions[key] = predictions[key].cpu().numpy().squeeze(0)  # remove batch dimension


In [6]:
#change depth to data and resize to 4x512x512x1
import numpy as np
from skimage.transform import resize

# 文件路径列表
file_paths = [
    "/data/train/train_30/2025-08-19_19-35-52/camconf_depth.npy",
    "/data/train/train_30/2025-08-19_19-35-53/camconf_depth.npy",
    "/data/train/train_30/2025-08-19_19-35-54/camconf_depth.npy",
    "/data/train/train_30/2025-08-19_19-35-55/camconf_depth.npy",
]

far=300.0
near=0.1
# 读取并 resize
resized_maps = []
for path in file_paths:
    norm_depth = np.load(path)  # shape: (256, 256)
    depth = far - norm_depth * (far - near) 
    resized = resize(depth, (512, 512), anti_aliasing=True, preserve_range=True)
    resized_maps.append(resized[..., np.newaxis])  # 添加通道维度

# 合并成 (4, 512, 512, 1)
depth_map = np.stack(resized_maps, axis=0)


print("Final shape:", depth_map.shape)  # 应该是 (4, 512, 512, 1)

# 可选：保存结果
# np.save("depth_map_4x512x512x1.npy", depth_map)

predictions["depth"] = depth_map.astype(np.float32)

Final shape: (4, 512, 512, 1)


In [7]:
import matplotlib.pyplot as plt
# plt.imshow(depth_map[0,..., 0])

In [8]:
#change world points from depth and extrinsic, intrinsic
from utils.geometry import unproject_depth_map_to_point_map
world_points = unproject_depth_map_to_point_map(depth_map, predictions["extrinsic"], predictions["intrinsic"])
predictions["world_points_from_depth"] = world_points
predictions["depth_conf"] = np.ones_like(predictions["depth"])

In [9]:
import os
from time import time
from utils.visual_util import predictions_to_glb

target_dir = "reconstruct_glb/"


glbfile = os.path.join(
    target_dir,
    f"{time()}.glb"
)
print(f"Exporting to {glbfile} ...")
glbscene = predictions_to_glb(
        predictions,
        conf_thres=3.0,
        filter_by_frames="All",
        mask_black_bg=False,
        mask_white_bg=False,
        show_cam=True,
        mask_sky=False,
        target_dir=target_dir,
        prediction_mode="42",
    )
glbscene.export(file_obj=glbfile)


/home/viplab/anaconda3/envs/vggt/lib/python3.11/site-packages/tqdm/auto.py:21: TqdmWarning: IProgress not found. Please update jupyter and ipywidgets. See https://ipywidgets.readthedocs.io/en/stable/user_install.html
  from .autonotebook import tqdm as notebook_tqdm


Exporting to reconstruct_glb/1769585623.5209668.glb ...
Building GLB scene
Using Depthmap and Camera Branch
GLB Scene built


b'glTF\x02\x00\x00\x00\x80\x13\x00\x01\xa4\r\x00\x00JSON{"scene":0,"scenes":[{"nodes":[0]}],"asset":{"version":"2.0","generator":"https://github.com/mikedh/trimesh"},"accessors":[{"componentType":5126,"type":"VEC3","byteOffset":0,"bufferView":0,"count":1048576,"max":[-99.1230239868164,25.4509220123291,91.29586029052734],"min":[-286.268798828125,-71.36116790771484,-109.93663787841797]},{"componentType":5121,"count":1048576,"normalized":true,"type":"VEC4","byteOffset":0,"bufferView":1,"max":[198,197,198,255],"min":[0,2,4,255]},{"componentType":5125,"type":"SCALAR","bufferView":2,"count":144,"max":[13],"min":[0]},{"componentType":5126,"type":"VEC3","byteOffset":0,"bufferView":3,"count":14,"max":[-6.349911212921143,100.00001525878906,0.4630734622478485],"min":[-23.575363159179688,86.58763885498047,-11.547920227050781]},{"componentType":5121,"normalized":true,"type":"VEC4","byteOffset":0,"bufferView":4,"count":14,"max":[255,0,40,255],"min":[255,0,40,255]},{"componentType":5126,"type":"VEC3"

In [10]:
del predictions